In [13]:
import pandas as pd
import plotly.graph_objects as go

In [14]:
df_bball_2026 = pd.read_csv("NBA Play-by-Play Data (1997-2026)/pbp2026.csv")

In [15]:
# df_nyk = df_bball_2026[df_bball_2026["team"] == "NYK"]
df_nyk = df_bball_2026.copy()

In [16]:
df_nyk["result"].unique()

<StringArray>
[nan, 'Missed', 'Made']
Length: 3, dtype: str

In [17]:
# df_nyk_made = df_nyk[(df_nyk["result"] == "Made") | (df_nyk["result"] == "Missed")]
df_nyk_made = df_nyk[(df_nyk["result"] == "Made")]

In [18]:
df_nyk_made["subtype"].unique()

<StringArray>
[                'Cutting Layup Shot',                 'Putback Layup Shot',
                 'Floating Jump shot',                  'Running Dunk Shot',
           'Turnaround Fadeaway shot',                          'Jump Shot',
                  'Driving Dunk Shot',                   'Pullup Jump shot',
                 'Driving Layup Shot',         'Driving Floating Jump Shot',
     'Driving Finger Roll Layup Shot',                  'Running Jump Shot',
                          'Hook Shot',                 'Running Layup Shot',
         'Driving Reverse Layup Shot',                         'Layup Shot',
                'Step Back Jump shot',                     'Jump Bank Shot',
             'Finger Roll Layup Shot',                     'Tip Layup Shot',
                'Alley Oop Dunk Shot',               'Turnaround Hook Shot',
                  'Putback Dunk Shot',               'Turnaround Jump Shot',
                 'Fadeaway Jump Shot',       'Running Alley Oo

In [19]:
df_nyk_made["player"].unique()

<StringArray>
[          'C. Holmgren',          'J. Smith Jr.',             'K. Durant',
               'L. Dort',           'A. Thompson',             'A. Sengun',
           'J. Williams', 'S. Gilgeous-Alexander',            'A. Wiggins',
           'R. Sheppard',
 ...
          'D. Whitehead',      'A. Antetokounmpo',              'J. Oduro',
              'C. Mañon',              'T. Keels',               'O. Sarr',
              'J. Tonje',             'T. Newton',            'E. Freeman',
               'H. Gray']
Length: 553, dtype: str

In [20]:
df_plotly = df_nyk_made[["player", "result", "x", "y", "desc"]]

In [21]:
df_plotly.head()

,player,result,x,y,desc
4,C. Holmgren,Made,0.0,13.0,Holmgren 1' Cutting Layup Shot (2 PTS) (Dort 1...
9,J. Smith Jr.,Made,-7.0,-5.0,Smith Jr. 1' Putback Layup (2 PTS)
10,C. Holmgren,Made,64.0,39.0,Holmgren 7' Floating Jump Shot (5 PTS) (Wallac...
17,K. Durant,Made,0.0,-1.0,Durant Running Dunk (2 PTS) (Thompson 1 AST)
18,C. Holmgren,Made,59.0,116.0,Holmgren 13' Turnaround Fadeaway (7 PTS)


In [22]:
print(df_plotly["x"].max())
print(df_plotly["y"].max())
print(df_plotly["x"].min())
print(df_plotly["y"].min())

250.0
734.0
-250.0
-50.0


In [23]:
import plotly.graph_objects as go

# 1. Definir dimensiones de la media cancha
# X va de -250 a 250 (ancho total = 500)
# Y va de -47.5 (fondo tras el aro) a 422.5 (altura de media cancha ~470 pies/decipies)
x_min, y_min = -250.0, -47.5
w, h = 500.0, 470.0  # Ancho y alto siempre positivos

x_max = x_min + w
y_max = y_min + h

fig = go.Figure()

# Filtrar jugadores únicos eliminando posibles valores nulos
players = [p for p in df_plotly['player'].dropna().unique().tolist()]

# 2. Añadir una traza por jugador
for player in players:
    subset = df_plotly[df_plotly['player'] == player]
    fig.add_trace(go.Scatter(
        x=subset['x'],
        y=subset['y'],
        mode='markers',
        name=player,
        marker=dict(size=8, opacity=0.8),
        text=subset['desc'],
        hovertemplate='<b>%{text}</b><br>Jugador: ' + str(player) + '<br>X: %{x}<br>Y: %{y}<extra></extra>'
    ))

# 3. Configurar botones de filtrado interactivo
buttons = [
    dict(
        label="Todos los tiros",
        method="update",
        args=[{"visible": [True] * len(players)},
              {"title": "Todos los tiros"}]
    )
]

for i, cat in enumerate(players):
    visibilidad = [False] * len(players)
    visibilidad[i] = True
    buttons.append(dict(
        label=f"{cat}",
        method="update",
        args=[{"visible": visibilidad},
              {"title": f"Tiros de: {cat}"}]
    ))

# 4. Rectángulo contenedor y layout
fig.update_layout(
    title="Mapa de tiros",
    updatemenus=[dict(
        active=0,
        buttons=buttons,
        x=0.0,
        y=1.15,
        xanchor="left",
        yanchor="top"
    )],
    shapes=[dict(
        type="rect",
        x0=x_min,
        y0=y_min,
        x1=x_max,
        y1=y_max,
        line=dict(color="black", width=2),
        fillcolor="rgba(240, 240, 240, 0.2)"
    )],
    xaxis=dict(
        range=[x_min - 10, x_max + 10],
        showgrid=True,
        zeroline=False
    ),
    yaxis=dict(
        range=[y_min - 10, y_max + 10],
        scaleanchor="x",
        scaleratio=1,
        showgrid=True,
        zeroline=False
    ),
    width=700,
    height=650
)

# Renderizar (usa renderer="browser" si da error de nbformat)
fig.show()